In [1]:
%pip install -q "ultralytics>=8.3" "supervision>=0.25" "opencv-python>=4.8" "numpy<3" pandas scikit-learn matplotlib gdown tqdm ipython

Note: you may need to restart the kernel to use updated packages.



[notice] A new release of pip is available: 24.0 -> 26.2.2
[notice] To update, run: E:\project\soccer\soccer\Scripts\python.exe -m pip install --upgrade pip


In [19]:
%pip install -q imageio-ffmpeg

Note: you may need to restart the kernel to use updated packages.



[notice] A new release of pip is available: 24.0 -> 26.2.2
[notice] To update, run: E:\project\soccer\soccer\Scripts\python.exe -m pip install --upgrade pip


In [1]:
from pathlib import Path
import os, time, math, warnings
import numpy as np, cv2, pandas as pd
from collections import defaultdict, deque, Counter
from IPython.display import display, Video
from ultralytics import YOLO
from sklearn.cluster import MiniBatchKMeans

ROOT=Path.cwd(); MODELS=ROOT/'models'; OUTPUT=ROOT/'outputs'
MODELS.mkdir(exist_ok=True); OUTPUT.mkdir(exist_ok=True)
SOURCE='soccer-ir.mp4'  
DEVICE='cpu'
IMG_SIZE=640
BALL_SIZE=640
PITCH_SIZE=640
PITCH_EVERY=20
BALL_EVERY=3
MAX_FRAMES=450
SHOW_LIVE=False     # True: periodically refresh notebook image (slower)
LIVE_EVERY=15
OUTPUT_VIDEO=OUTPUT/'soccer-ir_intelligence.mp4'
OUTPUT_CSV=OUTPUT/'player_tracking-ir.csv'
TEAM_COLORS=[(80,80,255),(255,80,80)] # BGR
print('Project:',ROOT)

Project: E:\project\soccer


In [2]:
import gdown
MODEL_IDS={
 'football-player-detection.pt':'17PXFNlx-jI7VjVo_vQnB1sONjRyvoB-q',
 'football-ball-detection.pt':'1isw4wx-MK9h9LMr36VvIWlJD6ppUvw7V',
 'football-pitch-detection.pt':'1Ma5Kt86tgpdjCTKfum79YMgNnSjcoOyf',
}
for filename, file_id in MODEL_IDS.items():
    path=MODELS/filename
    if not path.exists() or path.stat().st_size<1_000_000:
        print('Downloading',filename)
        gdown.download(id=file_id, output=str(path), quiet=False)
    if not path.exists() or path.stat().st_size<1_000_000:
        raise RuntimeError(f'Download failed: {filename}; see official setup.sh')
    print(filename,round(path.stat().st_size/1e6,1),'MB')
player_model=YOLO(str(MODELS/'football-player-detection.pt'))
ball_model=YOLO(str(MODELS/'football-ball-detection.pt'))
pitch_model=YOLO(str(MODELS/'football-pitch-detection.pt'))
print('Player classes:',player_model.names)
print('Pitch task:',pitch_model.task)
assert pitch_model.task=='pose', 'Expected keypoint/pose checkpoint for pitch detection' 

football-player-detection.pt 136.8 MB
football-ball-detection.pt 136.8 MB
football-pitch-detection.pt 140.2 MB
Player classes: {0: 'ball', 1: 'goalkeeper', 2: 'player', 3: 'referee'}
Pitch task: pose


In [3]:
# Official Roboflow SoccerPitchConfiguration landmark order (32 points, cm)
L,W=12000,7000
PBW,PBL=4100,2015
GBW,GBL=1832,550
R,PS=915,1100
VERTICES_CM=np.array([
 (0,0),(0,(W-PBW)/2),(0,(W-GBW)/2),(0,(W+GBW)/2),(0,(W+PBW)/2),(0,W),
 (GBL,(W-GBW)/2),(GBL,(W+GBW)/2),(PS,W/2),
 (PBL,(W-PBW)/2),(PBL,(W-GBW)/2),(PBL,(W+GBW)/2),(PBL,(W+PBW)/2),
 (L/2,0),(L/2,W/2-R),(L/2,W/2+R),(L/2,W),
 (L-PBL,(W-PBW)/2),(L-PBL,(W-GBW)/2),(L-PBL,(W+GBW)/2),(L-PBL,(W+PBW)/2),
 (L-PS,W/2),(L-GBL,(W-GBW)/2),(L-GBL,(W+GBW)/2),
 (L,0),(L,(W-PBW)/2),(L,(W-GBW)/2),(L,(W+GBW)/2),(L,(W+PBW)/2),(L,W),
 (L/2-R,W/2),(L/2+R,W/2)
],dtype=np.float32)
assert VERTICES_CM.shape==(32,2)
print('Official pitch geometry ready:',VERTICES_CM.shape)

Official pitch geometry ready: (32, 2)


In [7]:
from sklearn.cluster import KMeans
from collections import defaultdict, deque, Counter

# Set to 0 or 1 only if you know the goalkeeper's team; otherwise -1.
GOALKEEPER_TEAM = -1
TEAM_WARMUP_TRACKS = 8
TEAM_WARMUP_SAMPLES = 50
TEAM_CONFIDENCE_MARGIN = 0.13


def jersey_feature(frame, xyxy):
    """Robust torso color descriptor (Lab a/b statistics + histogram).
    Returns None for tiny/low-information crops. The returned vector is
    intentionally independent of brightness (L channel).
    """
    x1,y1,x2,y2 = np.asarray(xyxy).astype(int)
    h,w=frame.shape[:2]
    x1=max(0,x1);x2=min(w,x2);y1=max(0,y1);y2=min(h,y2)
    bw=x2-x1;bh=y2-y1
    if bw<9 or bh<22:return None
    # Narrow central torso: avoids grass, legs, head, and many arm pixels.
    xa=x1+int(.30*bw);xb=x1+int(.70*bw)
    ya=y1+int(.20*bh);yb=y1+int(.49*bh)
    roi=frame[ya:yb,xa:xb]
    if roi.size==0:return None
    lab=cv2.cvtColor(roi,cv2.COLOR_BGR2LAB).reshape(-1,3).astype(np.float32)
    hsv=cv2.cvtColor(roi,cv2.COLOR_BGR2HSV).reshape(-1,3)
    # Discard near-gray pixels when enough saturated jersey pixels exist.
    good=(hsv[:,1]>35)&(hsv[:,2]>35)&(hsv[:,2]<248)
    if good.sum()>=max(12,int(.15*len(good))): lab=lab[good]
    if len(lab)<12:return None
    ab=lab[:,1:3]
    median=np.median(ab,axis=0)
    q25=np.percentile(ab,25,axis=0)
    q75=np.percentile(ab,75,axis=0)
    # Scaling gives chromatic differences reasonable numerical magnitude.
    return np.concatenate([median,q25,q75]).astype(np.float32)/255.


def find_class(names, keyword, default=None):
    for i,label in names.items():
        if keyword in str(label).lower():return int(i)
    return default

PLAYER_CLASS=find_class(player_model.names,'player',2)
KEEPER_CLASS=find_class(player_model.names,'goalkeeper',1)
REF_CLASS=find_class(player_model.names,'referee',3)
print('Class IDs:',PLAYER_CLASS,KEEPER_CLASS,REF_CLASS)

class TeamEstimator:
    """Track-aggregated jersey clustering + persistent, conservative labels.
    Fit once after diverse track observations; do not refit and flip team IDs.
    Team 0/1 are arbitrary; uncertain assignments are -1.
    """
    def __init__(self):
        self.samples=[]
        self.model=None
        self.history=defaultdict(lambda:deque(maxlen=35))
        self.track_features=defaultdict(lambda:deque(maxlen=20))
        self.locked={}
        self.last_seen={}
        self.frame_count=0

    def update(self,frame,boxes,ids,classes):
        self.frame_count+=1
        result={}
        current={}
        for box,tid,cls in zip(boxes,ids,classes):
            tid=int(tid);cls=int(cls)
            if cls==KEEPER_CLASS:
                result[tid]=GOALKEEPER_TEAM
                continue
            if cls!=PLAYER_CLASS:continue
            feat=jersey_feature(frame,box)
            if feat is None:
                result[tid]=self.locked.get(tid,-1)
                continue
            self.track_features[tid].append(feat)
            self.last_seen[tid]=self.frame_count
            current[tid]=np.median(np.asarray(self.track_features[tid]),axis=0)
            if len(self.samples)<1200:self.samples.append((tid,feat))

        if self.model is None:
            # Cluster per-track median, not every frame: reduces team imbalance.
            track_medians=[np.median(np.asarray(v),axis=0)
                           for v in self.track_features.values() if len(v)>=3]
            if (len(track_medians)>=TEAM_WARMUP_TRACKS and
                    len(self.samples)>=TEAM_WARMUP_SAMPLES):
                data=np.asarray(track_medians,dtype=np.float32)
                model=KMeans(n_clusters=2,random_state=42,n_init=15)
                model.fit(data)
                sep=np.linalg.norm(model.cluster_centers_[0]-model.cluster_centers_[1])
                if sep>=0.055:
                    self.model=model
                    print(f'Team clustering initialized: {len(data)} tracks, separation={sep:.3f}')
        if self.model is None:
            return {int(tid):result.get(int(tid),-1) for tid in ids}

        for tid,feat in current.items():
            d=np.linalg.norm(self.model.cluster_centers_-feat,axis=1)
            best=int(np.argmin(d))
            confidence=float((max(d)-min(d))/(max(d)+min(d)+1e-8))
            if confidence>=TEAM_CONFIDENCE_MARGIN:
                self.history[tid].append(best)
            votes=Counter(self.history[tid]);total=sum(votes.values())
            if tid not in self.locked and total>=6:
                winning,count=votes.most_common(1)[0]
                if count/total>=.82:self.locked[tid]=int(winning)
            # Once enough reliable observations exist, keep identity stable.
            result[tid]=self.locked.get(tid,-1)
        return {int(tid):result.get(int(tid),self.locked.get(int(tid),-1)) for tid in ids}

def make_pitch(w=520,h=320):
    p=np.full((h,w,3),(45,115,45),dtype=np.uint8)
    cv2.rectangle(p,(12,12),(w-12,h-12),(255,255,255),2)
    cv2.line(p,(w//2,12),(w//2,h-12),(255,255,255),1)
    cv2.circle(p,(w//2,h//2),int(h*.12),(255,255,255),1)
    for x in [12,w-12]:
        sign=1 if x==12 else -1
        cv2.rectangle(p,(min(x,x+sign*75),h//2-85),(max(x,x+sign*75),h//2+85),(255,255,255),1)
    return p

def draw_radar(frame,positions,teams,valid):
    radar=make_pitch();rh,rw=radar.shape[:2]
    if valid:
        for tid,(xm,ym) in positions.items():
            if not (0<=xm<=L/100 and 0<=ym<=W/100):continue
            px=int(12+(xm/(L/100))*(rw-24));py=int(12+(ym/(W/100))*(rh-24))
            team=teams.get(tid,-1)
            color=TEAM_COLORS[team] if team in (0,1) else (255,255,255)
            cv2.circle(radar,(px,py),5,color,-1)
    target_w=min(frame.shape[1]//3,520)
    if target_w<120:return frame
    target_h=int(target_w*rh/rw)
    if target_h>frame.shape[0]//2:
        target_h=frame.shape[0]//2;target_w=int(target_h*rw/rh)
    radar=cv2.resize(radar,(target_w,target_h))
    x=frame.shape[1]-target_w-10;y=10
    frame[y:y+target_h,x:x+target_w]=radar
    return frame

def estimate_homography(result, vertices):
    if result.keypoints is None:return None,0
    xy=result.keypoints.xy.cpu().numpy()
    if len(xy)==0:return None,0
    pts=xy[0]; conf=(result.keypoints.conf.cpu().numpy()[0]
                       if result.keypoints.conf is not None else np.ones(len(pts)))
    n=min(len(pts),len(vertices));mask=(conf[:n]>.5)&(np.linalg.norm(pts[:n],axis=1)>1)
    if mask.sum()<6:return None,int(mask.sum())
    H,inliers=cv2.findHomography(pts[:n][mask].astype(np.float32),vertices[:n][mask].astype(np.float32),cv2.RANSAC,5.0)
    if H is None or inliers is None or inliers.sum()<5:return None,int(mask.sum())
    return H,int(inliers.sum())

def transform_feet(boxes,H):
    if H is None or len(boxes)==0:return None
    feet=np.stack(((boxes[:,0]+boxes[:,2])/2,boxes[:,3]),axis=1).astype(np.float32)
    return cv2.perspectiveTransform(feet.reshape(-1,1,2),H).reshape(-1,2)/100.0


Class IDs: 2 1 3


In [9]:
from IPython.display import clear_output, Image as IPImage

source=int(SOURCE) if isinstance(SOURCE,str) and SOURCE.isdigit() else SOURCE
cap=cv2.VideoCapture(source)
if not cap.isOpened():raise FileNotFoundError(f'Cannot open source: {SOURCE}')
fps=cap.get(cv2.CAP_PROP_FPS)
if not np.isfinite(fps) or fps<1:fps=25.0
width=int(cap.get(cv2.CAP_PROP_FRAME_WIDTH));height=int(cap.get(cv2.CAP_PROP_FRAME_HEIGHT))
if width<1 or height<1:raise RuntimeError('Invalid video dimensions')
writer=cv2.VideoWriter(str(OUTPUT_VIDEO),cv2.VideoWriter_fourcc(*'mp4v'),fps,(width,height))
if not writer.isOpened():raise RuntimeError('VideoWriter failed; check OpenCV codec support')
team_est=TeamEstimator();prev_metric={}; speeds={};last_ball=None;last_H=None
last_possession_frame=-10000
possession=Counter();last_possessor=None;records=[];frame_i=0;start=time.perf_counter()
try:
    while True:
        ok,frame=cap.read()
        if not ok or (MAX_FRAMES is not None and frame_i>=MAX_FRAMES):break
        t=frame_i/fps
        result=player_model.track(frame,persist=True,tracker='bytetrack.yaml',conf=.25,
                                  imgsz=IMG_SIZE,device=DEVICE,verbose=False)[0]
        boxes=np.empty((0,4));ids=[];classes=[]
        if result.boxes is not None and result.boxes.id is not None:
            boxes=result.boxes.xyxy.cpu().numpy()
            ids=result.boxes.id.int().cpu().tolist()
            classes=result.boxes.cls.int().cpu().tolist()
        teams=team_est.update(frame,boxes,ids,classes)
        if frame_i%BALL_EVERY==0:
            br=ball_model.predict(frame,conf=.15,imgsz=BALL_SIZE,device=DEVICE,verbose=False)[0]
            last_ball=None
            if br.boxes is not None and len(br.boxes)>0:
                idx=int(br.boxes.conf.argmax().item())
                bb=br.boxes.xyxy[idx].cpu().numpy()
                last_ball=((float(bb[0]+bb[2])/2),(float(bb[1]+bb[3])/2))
        if VERTICES_CM is not None and frame_i%PITCH_EVERY==0:
            pr=pitch_model.predict(frame,imgsz=PITCH_SIZE,device=DEVICE,verbose=False)[0]
            candidate,n_inliers=estimate_homography(pr,VERTICES_CM)
            if candidate is not None:last_H=candidate
        metric=transform_feet(boxes,last_H) if VERTICES_CM is not None else None
        radar_pos={}
        best_id=None;best_d=float('inf')
        for i,(box,tid,cls) in enumerate(zip(boxes,ids,classes)):
            x1,y1,x2,y2=map(int,box);foot=((x1+x2)//2,y2)
            team=teams.get(tid,-1);color=TEAM_COLORS[team] if team in (0,1) else (220,220,220)
            if cls==REF_CLASS:color=(0,255,255)
            cv2.ellipse(frame,foot,(max(5,(x2-x1)//2),max(3,(x2-x1)//7)),0,0,360,color,2)
            speed=None
            if metric is not None:
                x_m,y_m=map(float,metric[i]);radar_pos[tid]=(x_m,y_m)
                prev=prev_metric.get(tid)
                if prev is not None:
                    dt=t-prev[2];dist=math.hypot(x_m-prev[0],y_m-prev[1])
                    if dt>0 and dist/dt<12:
                        raw=3.6*dist/dt
                        speeds[tid]=.8*speeds.get(tid,raw)+.2*raw
                prev_metric[tid]=(x_m,y_m,t)
                speed=speeds.get(tid)
            label=f'ID {tid} T{team if team>=0 else "?"}'
            if speed is not None:label+=f' {speed:.1f} km/h'
            cv2.putText(frame,label,(x1,max(18,y1-6)),cv2.FONT_HERSHEY_SIMPLEX,.45,color,2)
            records.append(dict(frame=frame_i,time_s=t,track_id=tid,class_id=cls,team=team,
                                foot_x_px=foot[0],foot_y_px=foot[1],
                                x_m=radar_pos.get(tid,(None,None))[0],
                                y_m=radar_pos.get(tid,(None,None))[1],speed_kmh=speed))
            if last_ball is not None and cls in (PLAYER_CLASS,KEEPER_CLASS):
                d=math.hypot(foot[0]-last_ball[0],foot[1]-last_ball[1])
                threshold=max(30,(y2-y1)*.55)
                if d<threshold and d<best_d:best_id=tid;best_d=d
        if last_ball is not None:
            cv2.circle(frame,tuple(map(int,last_ball)),7,(0,255,255),-1)
        
        if best_id is not None and teams.get(best_id,-1) in (0,1):
            last_possessor=teams[best_id]
            last_possession_frame=frame_i
        
        if last_possessor in (0,1) and frame_i-last_possession_frame<=max(3,BALL_EVERY*2):
            possession[last_possessor]+=1
        frame=draw_radar(frame,radar_pos,teams,last_H is not None)
        total=possession[0]+possession[1]
        p0=100*possession[0]/total if total else 0
        p1=100*possession[1]/total if total else 0
        cv2.rectangle(frame,(0,0),(min(width,450),48),(15,15,15),-1)
        cv2.putText(frame,f'Possession estimate: T0 {p0:.0f}%  T1 {p1:.0f}%',
                    (8,30),cv2.FONT_HERSHEY_SIMPLEX,.6,(255,255,255),2)
        writer.write(frame)
        if SHOW_LIVE and frame_i%LIVE_EVERY==0:
            clear_output(wait=True)
            ok,jpg=cv2.imencode('.jpg',cv2.resize(frame,(min(960,width),int(height*min(960,width)/width))))
            if ok:display(IPImage(data=jpg.tobytes()))
        frame_i+=1
finally:
    cap.release();writer.release()
pd.DataFrame.from_records(records,columns=['frame','time_s','track_id','class_id','team','foot_x_px','foot_y_px','x_m','y_m','speed_kmh']).to_csv(OUTPUT_CSV,index=False)
print(f'Processed {frame_i} frames in {time.perf_counter()-start:.1f}s')
print('Video:',OUTPUT_VIDEO,'CSV:',OUTPUT_CSV)


Team clustering initialized: 9 tracks, separation=0.415
Processed 450 frames in 421.8s
Video: E:\project\soccer\outputs\soccer-ir_intelligence.mp4 CSV: E:\project\soccer\outputs\player_tracking-ir.csv


In [10]:
from pathlib import Path
from IPython.display import Video, display
import imageio_ffmpeg
import subprocess
import cv2


input_video = Path("outputs/soccer-ir_intelligence.mp4")
output_video = Path("outputs/soccer-ir_intelligence_h264.mp4")


if not input_video.exists():
    raise FileNotFoundError(
        f"Video not found: {input_video.resolve()}"
    )

if input_video.stat().st_size == 0:
    raise RuntimeError("The output video is empty.")


cap = cv2.VideoCapture(str(input_video))
success, frame = cap.read()
cap.release()

if not success:
    raise RuntimeError(
        "OpenCV cannot read the video. "
        "The file may be corrupted or incomplete."
    )

print("Original video found.")
print("Converting to H.264...")


ffmpeg = imageio_ffmpeg.get_ffmpeg_exe()

# Convert to browser-compatible MP4
command = [
    ffmpeg,
    "-y",
    "-i", str(input_video),
    "-c:v", "libx264",
    "-preset", "veryfast",
    "-crf", "23",
    "-pix_fmt", "yuv420p",
    "-movflags", "+faststart",
    "-an",
    str(output_video)
]

result = subprocess.run(
    command,
    capture_output=True,
    text=True
)

if result.returncode != 0:
    raise RuntimeError(result.stderr[-3000:])

print("Conversion completed!")
print("Output:", output_video.resolve())


display(
    Video(
        filename=str(output_video),
        embed=True,
        width=960,
        html_attributes="controls"
    )
)

Original video found.
Converting to H.264...
Conversion completed!
Output: E:\project\soccer\outputs\soccer-ir_intelligence_h264.mp4


In [11]:
import cv2, numpy as np, pandas as pd, math, subprocess
from pathlib import Path
from collections import Counter, defaultdict
from ultralytics import YOLO
from IPython.display import display, Video

OUTPUT_DIR=Path('outputs'); OUTPUT_DIR.mkdir(exist_ok=True)
VIDEO_PATH=str(globals().get('SOURCE','soccer-ir.mp4'))
TRACK_CSV=Path(globals().get('OUTPUT_CSV', OUTPUT_DIR/'player_tracking-ir.csv'))
BALL_MODEL_PATH=str(Path('models/football-ball-detection.pt'))
ANNOTATED=Path(globals().get('OUTPUT_VIDEO',OUTPUT_DIR/'soccer-ir_intelligence.mp4'))
OUT_MP4=OUTPUT_DIR/'soccer-ir_pass_main_camera.mp4'
OUT_H264=OUTPUT_DIR/'soccer-ir_pass_main_camera_h264.mp4'
EVENTS_CSV=OUTPUT_DIR/'candidate_passes_v4.csv'
STATS_CSV=OUTPUT_DIR/'team_pass_stats_v4.csv'
OPTIONS_CSV=OUTPUT_DIR/'receiver_options_v4.csv'
BALL_CSV=OUTPUT_DIR/'ball_observations_v4.csv'
BALL_IMGSZ=640; BALL_CONF=.12
MIN_STABLE_OBSERVATIONS=2; MAX_OWNER_GAP_FRAMES=12
MIN_PASS_M=3.; MAX_PASS_M=50.; MAX_TRANSFER_SEC=2.5
MAX_ANALYSIS_FRAMES=None; DISPLAY_SECONDS=1.3
ASSOCIATION_RADIUS=65; MAX_BALL_JUMP_PX=110
MIN_OPTION_QUALITY=.55; MIN_LANE_QUALITY=.50
MAX_VISIBLE_ARROWS=3; DRAW_CONTINUOUS_OPTIONS=True
TEAM_COLORS={0:(255,180,60),1:(60,100,255)}
# Set team attacking direction after checking the video (+1 towards x=120m, -1 towards x=0m).
ATTACK_DIRECTION={0:1,1:-1}
FAVORABLE_THRESHOLD=.60

if not TRACK_CSV.exists():
    raise FileNotFoundError(f'Missing {TRACK_CSV}. Run original tracking cell 6 first.')
df=pd.read_csv(TRACK_CSV)
required={'frame','track_id','team','foot_x_px','foot_y_px','x_m','y_m'}
missing=required-set(df.columns)
if missing: raise ValueError(f'Tracking CSV missing columns: {sorted(missing)}')
for col in required:
    df[col]=pd.to_numeric(df[col],errors='coerce')
tracking=df.dropna(subset=list(required)).copy()
tracking=tracking[tracking.team.isin([0,1])]
tracking=tracking[(tracking.frame>=0)&(tracking.track_id>=0)]
tracking[['frame','track_id','team']]=tracking[['frame','track_id','team']].astype(int)
tracking=tracking.drop_duplicates(['frame','track_id'],keep='last')
tracking_by_frame={int(k):v for k,v in tracking.groupby('frame')}
if not tracking_by_frame: raise RuntimeError('No valid tracking data with pitch coordinates. Check pitch calibration.')
cap=cv2.VideoCapture(VIDEO_PATH)
if not cap.isOpened():raise FileNotFoundError(VIDEO_PATH)
FPS=float(cap.get(cv2.CAP_PROP_FPS)); FPS=FPS if np.isfinite(FPS) and FPS>0 else 25.
W=int(cap.get(3));H=int(cap.get(4));VIDEO_FRAMES=int(cap.get(cv2.CAP_PROP_FRAME_COUNT));cap.release()
END_FRAME=min(VIDEO_FRAMES,max(tracking_by_frame)+1)
if MAX_ANALYSIS_FRAMES is not None:END_FRAME=min(END_FRAME,int(MAX_ANALYSIS_FRAMES))
if not Path(BALL_MODEL_PATH).exists():raise FileNotFoundError(BALL_MODEL_PATH)
ball_model=globals().get('ball_model') or YOLO(BALL_MODEL_PATH)
print('Tracking CSV:',TRACK_CSV,'rows:',len(tracking),'frames:',len(tracking_by_frame))
print('Source:',W,H,'FPS:',FPS,'Analyzing frames:',END_FRAME)
print('Annotated video:',ANNOTATED if ANNOTATED.exists() else 'not found; using source')

Tracking CSV: E:\project\soccer\outputs\player_tracking-ir.csv rows: 4840 frames: 410
Source: 1920 1080 FPS: 50.0 Analyzing frames: 450
Annotated video: E:\project\soccer\outputs\soccer-ir_intelligence.mp4


In [12]:
def clip01(x):return float(np.clip(x,0,1))
def distance(a,b):return float(np.linalg.norm(np.asarray(a,float)-np.asarray(b,float)))
def point_segment_distance(p,a,b):
    p=np.asarray(p,float);a=np.asarray(a,float);b=np.asarray(b,float)
    ab=b-a; t=np.clip(np.dot(p-a,ab)/max(np.dot(ab,ab),1e-9),0,1)
    return float(np.linalg.norm(p-(a+t*ab))),float(t)

def evaluate_receiver_options(receiver_id,team,players):
    own=players[(players.track_id==receiver_id)&(players.team==team)]
    if own.empty:return None
    receiver=own.iloc[0];origin=np.array([receiver.x_m,receiver.y_m],float)
    if not np.isfinite(origin).all():return None
    opponents=players[players.team!=team][['x_m','y_m']].to_numpy(float)
    teammates=players[(players.team==team)&(players.track_id!=receiver_id)]
    nearest=min((distance(origin,p) for p in opponents),default=20.)
    pressure=clip01((8.-nearest)/8.)
    open_space=clip01(nearest/10.)
    options=[]
    for r in teammates.itertuples(index=False):
        target=np.array([r.x_m,r.y_m],float);d=distance(origin,target)
        if not 3<=d<=40:continue
        nearest_target=min((distance(target,p) for p in opponents),default=20.)
        target_space=clip01(nearest_target/9.)
        lane_clearance=min((point_segment_distance(p,origin,target)[0] for p in opponents
                            if .08<point_segment_distance(p,origin,target)[1]<.92),default=12.)
        lane_quality=clip01(lane_clearance/4.)
        advance=(target[0]-origin[0])*ATTACK_DIRECTION[int(team)]
        progression=clip01(.5+advance/30.)
        length_score=clip01((40.-d)/32.)
        q=clip01(.30*target_space+.30*lane_quality+.25*progression+.15*length_score)
        viable=bool(q>=MIN_OPTION_QUALITY and lane_quality>=MIN_LANE_QUALITY and nearest_target>=2.5)
        options.append(dict(target_id=int(r.track_id),quality=q,lane_quality=lane_quality,
                            target_space=target_space,progression=progression,distance_m=d,viable=viable))
    viable=[o for o in options if o['viable']]
    
    best=np.mean(sorted((o['quality'] for o in viable),reverse=True)[:3]) if viable else 0.
    choice=clip01(len(viable)/4.)
    quality=clip01(.50*best+.20*choice+.20*open_space+.10*(1-pressure))
    return dict(quality=quality*100,favorable=bool(quality>=FAVORABLE_THRESHOLD and len(viable)>=1),
                num_options=len(viable),total_options=len(options),pressure=pressure,open_space=open_space,
                options=sorted(options,key=lambda o:o['quality'],reverse=True))

def ball_candidate(frame,previous=None):
    result=ball_model.predict(frame,conf=BALL_CONF,imgsz=BALL_IMGSZ,device='cpu',verbose=False)[0]
    if result.boxes is None or len(result.boxes)==0:return None,0.
    boxes=result.boxes.xyxy.cpu().numpy();confs=result.boxes.conf.cpu().numpy();candidates=[]
    for box,conf in zip(boxes,confs):
        x1,y1,x2,y2=box;bw=x2-x1;bh=y2-y1
        if bw<=0 or bh<=0 or bw>max(45,W*.045) or bh>max(45,H*.07):continue
        ratio=bw/bh
        if not .35<=ratio<=2.8:continue
        center=np.array([(x1+x2)/2,(y1+y2)/2],float)
        if previous is not None:
            jump=distance(center,previous)
            if jump>MAX_BALL_JUMP_PX:continue
            motion=np.exp(-jump/60.)
        else:motion=.5
        candidates.append((.75*float(conf)+.25*motion,center,float(conf)))
    if not candidates:return None,0.
    _,center,conf=max(candidates,key=lambda x:x[0]);return center,conf

def closest_owner_candidate(ball,players):
    if ball is None or players.empty:return None,None,None
    pts=players[['foot_x_px','foot_y_px']].to_numpy(float)
    proxy=pts.copy();proxy[:,1]-=.035*H
    ds=np.minimum(np.linalg.norm(pts-ball,axis=1),np.linalg.norm(proxy-ball,axis=1))
    j=int(np.argmin(ds));row=players.iloc[j]
    if ds[j]>ASSOCIATION_RADIUS:return None,None,float(ds[j])
    return int(row.track_id),int(row.team),float(ds[j])

In [13]:
cap=cv2.VideoCapture(VIDEO_PATH)
observations=[];events=[];option_rows=[];diag=Counter()
prev_ball=None;last_ball_frame=-10000
stable_id=None;stable_team=None;stable_last_seen=None;stable_last_xy=None
pending_id=None;pending_count=0;pending_start=None
last_change=-10000
try:
    for fi in range(END_FRAME):
        ok,frame=cap.read()
        if not ok:break
        players=tracking_by_frame.get(fi)
        if players is None or players.empty:
            observations.append((fi,np.nan,np.nan,np.nan,np.nan,np.nan));continue
        ball,conf=ball_candidate(frame,prev_ball if fi-last_ball_frame<=3 else None)
        if ball is not None:prev_ball=ball;last_ball_frame=fi;diag['ball_frames']+=1
        owner,team,od=closest_owner_candidate(ball,players)
        observations.append((fi,ball[0] if ball is not None else np.nan,
                             ball[1] if ball is not None else np.nan,conf,
                             owner if owner is not None else np.nan,od if od is not None else np.nan))
        if owner is None:
            pending_id=None;pending_count=0;pending_start=None
            continue
        diag['near_player_frames']+=1
        if owner==stable_id:
            row=players[players.track_id==owner]
            if not row.empty:
                stable_last_xy=np.array([row.iloc[0].x_m,row.iloc[0].y_m],float)
                stable_last_seen=fi
            pending_id=None;pending_count=0;pending_start=None
            continue
        if owner==pending_id:pending_count+=1
        else:pending_id=owner;pending_count=1;pending_start=fi
        if pending_count<MIN_STABLE_OBSERVATIONS:continue
        row=players[players.track_id==owner]
        if row.empty:continue
        new_xy=np.array([row.iloc[0].x_m,row.iloc[0].y_m],float)
        receive_frame=int(pending_start)
        receive_players=tracking_by_frame.get(receive_frame,players)
        if stable_id is not None and stable_last_seen is not None and stable_last_xy is not None:
            dt=(receive_frame-stable_last_seen)/FPS
            gap=receive_frame-stable_last_seen
            meters=distance(stable_last_xy,new_xy)
            diag['owner_changes']+=1
            if (team==stable_team and owner!=stable_id and MIN_PASS_M<=meters<=MAX_PASS_M
                and 0<=dt<=MAX_TRANSFER_SEC and gap<=MAX_OWNER_GAP_FRAMES
                and fi-last_change>3):
                evaluation=evaluate_receiver_options(owner,team,receive_players)
                if evaluation is not None:
                    pid=len(events)+1
                    events.append(dict(pass_id=pid,frame=receive_frame,confirmation_frame=fi,
                      time_s=receive_frame/FPS,team=team,passer_id=stable_id,receiver_id=owner,
                      pass_distance_m=round(meters,2),transfer_time_s=round(dt,3),
                      quality=round(evaluation['quality'],2),favorable=evaluation['favorable'],
                      num_options=evaluation['num_options'],total_options=evaluation['total_options'],
                      pressure=round(evaluation['pressure'],3),open_space=round(evaluation['open_space'],3)))
                    for opt in evaluation['options']:
                        option_rows.append(dict(pass_id=pid,frame=receive_frame,receiver_id=owner,**opt))
                    diag['candidate_passes']+=1
            elif team!=stable_team:diag['opponent_changes']+=1
            else:diag['rejected_transfers']+=1
        stable_id=owner;stable_team=team;stable_last_seen=fi;stable_last_xy=new_xy
        pending_id=None;pending_count=0;pending_start=None;last_change=fi
finally:cap.release()
ball_df=pd.DataFrame(observations,columns=['frame','ball_x','ball_y','confidence','near_player_id','near_player_distance_px'])
passes_df=pd.DataFrame(events,columns=['pass_id','frame','confirmation_frame','time_s','team','passer_id','receiver_id','pass_distance_m','transfer_time_s','quality','favorable','num_options','total_options','pressure','open_space'])
options_df=pd.DataFrame(option_rows)
ball_df.to_csv(BALL_CSV,index=False);passes_df.to_csv(EVENTS_CSV,index=False);options_df.to_csv(OPTIONS_CSV,index=False)
if passes_df.empty:
    team_stats=pd.DataFrame(columns=['team','candidate_passes','average_quality','favorable_percent','average_options'])
else:
    team_stats=passes_df.groupby('team').agg(candidate_passes=('pass_id','size'),average_quality=('quality','mean'),favorable_percent=('favorable','mean'),average_options=('num_options','mean')).reset_index()
    team_stats['favorable_percent']*=100
team_stats.round(2).to_csv(STATS_CSV,index=False)
print('Diagnostics:',dict(diag));display(passes_df.head(15));display(team_stats.round(2))

Diagnostics: {'ball_frames': 134, 'near_player_frames': 95, 'owner_changes': 5, 'rejected_transfers': 1, 'opponent_changes': 4}


,pass_id,frame,confirmation_frame,time_s,team,passer_id,receiver_id,pass_distance_m,transfer_time_s,quality,favorable,num_options,total_options,pressure,open_space


,team,candidate_passes,average_quality,favorable_percent,average_options


In [14]:
RENDER_VIDEO=str(ANNOTATED if ANNOTATED.exists() else VIDEO_PATH)
src=cv2.VideoCapture(RENDER_VIDEO)
if not src.isOpened():raise FileNotFoundError(RENDER_VIDEO)
if (int(src.get(3)),int(src.get(4)))!=(W,H) or int(src.get(cv2.CAP_PROP_FRAME_COUNT))<END_FRAME:
    src.release();src=cv2.VideoCapture(VIDEO_PATH)
writer=cv2.VideoWriter(str(OUT_MP4),cv2.VideoWriter_fourcc(*'mp4v'),FPS,(W,H))
if not writer.isOpened():raise RuntimeError('Video writer failed')
events_by_frame={int(r.frame):r for r in passes_df.itertuples(index=False)}
ball_by_frame=ball_df.set_index('frame')
active=None;active_until=-1;drawn=0
cumulative=Counter();qsum=defaultdict(float);favorable=Counter()
def put(frame,s,xy,color=(255,255,255),scale=.55):
    cv2.putText(frame,str(s),tuple(map(int,xy)),cv2.FONT_HERSHEY_SIMPLEX,scale,color,2,cv2.LINE_AA)
try:
    for fi in range(END_FRAME):
        ok,frame=src.read()
        if not ok:break
        if fi in events_by_frame:
            active=events_by_frame[fi];active_until=fi+int(DISPLAY_SECONDS*FPS)
            t=int(active.team);cumulative[t]+=1;qsum[t]+=float(active.quality);favorable[t]+=int(active.favorable)
        players=tracking_by_frame.get(fi)
        if players is not None and not players.empty:
            receiver_id=None;event_active=active is not None and fi<=active_until
            if event_active and int(active.receiver_id) in players.track_id.values:
                receiver_id=int(active.receiver_id)
            elif DRAW_CONTINUOUS_OPTIONS and fi in ball_by_frame.index:
                candidate=ball_by_frame.at[fi,'near_player_id']
                if pd.notna(candidate) and int(candidate) in players.track_id.values:receiver_id=int(candidate)
            if receiver_id is not None:
                receiver=players[players.track_id==receiver_id].iloc[0]
                evaluation=evaluate_receiver_options(receiver_id,int(receiver.team),players)
                if evaluation is not None:
                    origin=(int(receiver.foot_x_px),int(receiver.foot_y_px))
                    cv2.circle(frame,origin,22,TEAM_COLORS[int(receiver.team)],3)
                    count=0
                    for opt in evaluation['options']:
                        if not opt['viable']:continue
                        target_row=players[players.track_id==opt['target_id']]
                        if target_row.empty:continue
                        tr=target_row.iloc[0];target=(int(tr.foot_x_px),int(tr.foot_y_px))
                        color=(60,230,90) if opt['quality']>=.75 else (0,210,255)
                        cv2.arrowedLine(frame,origin,target,color,2,cv2.LINE_AA,tipLength=.07)
                        mid=((origin[0]+target[0])//2,(origin[1]+target[1])//2)
                        put(frame,f"{opt['quality']*100:.0f}",mid,color,.45)
                        count+=1;drawn+=1
                        if count>=MAX_VISIBLE_ARROWS:break
                    cv2.rectangle(frame,(10,8),(min(W-1,620),min(H-1,118)),(25,25,25),-1)
                    put(frame,f"{'RECEPTION' if event_active else 'BALL-NEAR PLAYER'} | Team {int(receiver.team)} | ID {receiver_id}",(20,38))
                    put(frame,f"Viable next passes: {evaluation['num_options']} | Quality: {evaluation['quality']:.0f}/100",(20,72))
                    put(frame,f"Pressure: {evaluation['pressure']:.2f} | Space: {evaluation['open_space']:.2f}",(20,104))
        for t in (0,1):
            n=cumulative[t];mean=qsum[t]/n if n else 0.;pct=100*favorable[t]/n if n else 0.
            put(frame,f'Team {t}: {n} passes | Q {mean:.0f} | favorable {pct:.0f}%',(15,H-65+30*t),TEAM_COLORS[t],.52)
        writer.write(frame)
finally:src.release();writer.release()
print('MP4:',OUT_MP4,'arrows:',drawn)
try:
    import imageio_ffmpeg
    cmd=[imageio_ffmpeg.get_ffmpeg_exe(),'-y','-i',str(OUT_MP4),'-c:v','libx264','-preset','veryfast','-crf','23','-pix_fmt','yuv420p','-movflags','+faststart','-an',str(OUT_H264)]
    p=subprocess.run(cmd,capture_output=True,text=True)
    if p.returncode:raise RuntimeError(p.stderr[-1500:])
    display(Video(filename=str(OUT_H264),embed=True,width=960))
except ImportError:
    print('Install imageio-ffmpeg for H264 notebook preview.')

MP4: outputs\soccer-ir_pass_main_camera.mp4 arrows: 225
